In [6]:
import plotly.io as pio
pio.renderers.default = "notebook"
import pandas as pd
import matplotlib.pyplot as plt
from matplotlib import colormaps
import numpy as np
import geopandas as gpd
import fiona
import seaborn as sns
from sklearn.linear_model import LinearRegression
from sklearn.metrics import r2_score
from scipy import stats
import folium
import plotly.graph_objects as go
from plotly.subplots import make_subplots

# Dataframes

In [7]:
# NJ Counties Dataframe with Geographical coordinates
nj_ct=gpd.read_file('/Users/bathnayfleurima/Downloads/Gifted/NJ_Counties_3424_-9015801819776815888.geojson')
nj_ct=nj_ct.drop(['CO','GNIS','FIPSSTCO','OBJECTID',
                 'COUNTY','GNIS_NAME','FIPSCO'], axis=1).set_index('COUNTY_LABEL')
nj_ct.loc['Charters']= np.nan
nj_ct.head(5)

,ACRES,SQ_MILES,POP2020,POP2010,POP2000,POP1990,POP1980,POPDEN2020,POPDEN2010,POPDEN2000,POPDEN1990,POPDEN1980,REGION,geometry
COUNTY_LABEL,,,,,,,,,,,,,,
Atlantic County,390813.840968,610.646627,274534.0,274549.0,252552.0,275372.0,204615.0,450.0,450.0,414.0,451.0,335.0,COASTAL,"POLYGON ((-74.67437 39.68858, -74.67433 39.688..."
Bergen County,153491.054911,239.829773,955732.0,905116.0,884118.0,829592.0,849843.0,3985.0,3774.0,3686.0,3459.0,3544.0,NORTHEASTERN,"POLYGON ((-73.90569 40.98315, -73.90591 40.982..."
Burlington County,524901.239967,820.158187,461860.0,448734.0,423394.0,395066.0,362542.0,563.0,547.0,516.0,482.0,442.0,SOUTHERN,"POLYGON ((-74.69864 40.18226, -74.69838 40.182..."
Camden County,145594.972008,227.492144,523485.0,513657.0,508932.0,532498.0,471650.0,2301.0,2258.0,2237.0,2341.0,2073.0,SOUTHERN,"POLYGON ((-75.03314 39.99483, -75.03299 39.994..."
Cape May County,183125.841721,286.134128,95263.0,97265.0,102326.0,95089.0,82266.0,333.0,340.0,358.0,332.0,288.0,COASTAL,"POLYGON ((-74.85962 39.31897, -74.85955 39.318..."


# List of NJ Counties

In [11]:
county_list=[]
for l in nj_ct.index:
    county_list.append(l)
county_list.append('Charters')
county_list.pop(22)

'Charters'

# Index

In [12]:
county_index=pd.Index(county_list)
county_index

Index(['Atlantic County', 'Bergen County', 'Burlington County',
       'Camden County', 'Cape May County', 'Cumberland County', 'Essex County',
       'Gloucester County', 'Hudson County', 'Hunterdon County',
       'Mercer County', 'Middlesex County', 'Monmouth County', 'Morris County',
       'Ocean County', 'Passaic County', 'Salem County', 'Somerset County',
       'Sussex County', 'Union County', 'Warren County', 'Charters'],
      dtype='object')

In [13]:
# NJ School Districts Dataframe

district_df=pd.read_excel('/Users/bathnayfleurima/Desktop/Database_DistrictStateDetail_NJ.xlsx',sheet_name=5,)

district_cnt=district_df.value_counts('CountyName').to_frame().sort_index()
district_cnt=district_cnt.rename(columns={'count':'DISTRICT_COUNT'})
district_cnt=district_cnt.drop(index=['State'])
district_cnt.index=county_index
district_cnt=district_cnt.rename_axis('COUNTY_LABEL')
district_cnt=district_cnt.astype('int32')


In [14]:
# NJ Total Number of Schools by Grade types Dataframe
cols=['County Name','District Name','School Name','Pre-K','Kindergarten','Grade 1','Grade 2','Grade 3','Grade 4','Grade 5','Grade 6','Grade 7','Grade 8','Grade 9','Grade 10','Grade 11','Grade 12','Post Grad','Adult Ed.']
sch_type_df=pd.read_excel('/Users/bathnayfleurima/Downloads/NJPubSchool.xlsx', header=3, usecols=cols)
sch_type_df.head(3)

,County Name,District Name,School Name,Pre-K,Kindergarten,Grade 1,Grade 2,Grade 3,Grade 4,Grade 5,Grade 6,Grade 7,Grade 8,Grade 9,Grade 10,Grade 11,Grade 12,Post Grad,Adult Ed.
0,ATLANTIC,Absecon Public Schools District,Emma C Attales,NaN,NaN,NaN,NaN,NaN,NaN,1.0,1.0,1.0,1.0,NaN,NaN,NaN,NaN,NaN,NaN
1,ATLANTIC,Absecon Public Schools District,H Ashton Marsh,1.0,1.0,1.0,1.0,1.0,1.0,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2,ATLANTIC,Atlantic City School District,Atlantic City High School,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,1.0,1.0,1.0,1.0,NaN,NaN


In [15]:
# NJ Education Spending Dataframe
finance_df=pd.read_excel('/Users/bathnayfleurima/Desktop/Database_DistrictStateDetail_NJ.xlsx',sheet_name=5, usecols=['CountyName','DistrictName','2021 Spending'], dtype={'2021 Spending':float} )
finance_df=finance_df.groupby('CountyName')['2021 Spending'].sum()
finance_df=finance_df.drop('State')


In [16]:
# NJ Total Number of Students Enrolled
enroll_df=pd.read_excel('/Users/bathnayfleurima/Downloads/Database_DistrictStateDetail (2).xlsx', sheet_name=2)
enroll_df=enroll_df[(enroll_df['CountyName'] != 'State') ]

enroll_ct=enroll_df.groupby('CountyName')['Total'].sum()

In [17]:
# NJ Number of Schools by District Dataframe

col_list=['County Name','District Name','School Name','Address1','Address2','City','State','Zip']
sch_det_df=pd.read_excel('/Users/bathnayfleurima/Downloads/NJPubSchool.xlsx', header=3, usecols=col_list)
sch_num_ct=sch_det_df.groupby(by='County Name')['School Name'].count().to_frame().rename(columns={'School Name':'School Count'})
sch_num_ct.loc['CHARTERS']=np.nan


In [18]:
# Merged Data Dataframe

nj_ct_merged=nj_ct.merge(district_cnt, how='inner', on='COUNTY_LABEL' )
nj_ct_merged['SCH_COUNT']=sch_num_ct['School Count'].values
nj_ct_merged['SCH_DIST_RATIO']=nj_ct_merged['SCH_COUNT']/nj_ct_merged['DISTRICT_COUNT']
nj_ct_merged['TOT_STUDENT']=enroll_ct.values
nj_ct_merged['2021_SPENDING']=finance_df.values

In [19]:
nj_geo_Json=nj_ct.to_geo_dict()

# NJ Map with Data


In [37]:
m_ap=nj_ct_merged.explore(column='TOT_STUDENT',popup=False)
m_ap.zoom_start=10
m_ap

# NJ Education Data Snapshot

In [25]:
# NOTE (Bar Graph)
# The average number of schools based on the grades that they contain. 
# Not all schools were neatly packaged in the traditional elementary, middle and high school categories.  
# A significant number of schools had grades that spanned two or three categories.

fig=make_subplots(rows=2, cols=2,
                 specs=[[{'rowspan':2,'type':'map'},{'type':'indicator'}],[None,{'type':'xy'}]],
                 subplot_titles=('# of Schools by County','# of Schools Statewide','Avg. # of Schools by Categorical Grades'))

fig.add_trace(go.Choroplethmap(geojson=nj_geo_Json,  locations=nj_ct_merged.index, z=nj_ct_merged['SCH_COUNT'], showlegend=False),row=1, col=1)
fig.add_trace(go.Indicator(mode='number', value= 2522, domain={'x':[0,0.5], 'y':[0,0.5]}),row=1, col=2)
fig.add_trace(go.Bar(x=['Avg. Elem Grades','Avg. Mid Grades','Avg. High Grades','Avg. Adult'], y=[1292,822,495,36], text=[1292,822,495,36], marker_color=['red','blue','green','yellow']),row=2, col=2,)
fig.update_layout(paper_bgcolor='whitesmoke',title_text='New Jersey Education Snapshot', 
                  title_x=0.5, title_font_size=50, barmode='group', title_font_lineposition='under',map={
        "center": {"lat": 39.95, "lon": -74.16},
        "zoom": 6, 
        "style": "open-street-map"})
fig.update_geos(fitbounds='locations', visible=True)

In [26]:
labels_list=['White','Hispanic', 'Black or African American', 'Asian', 'Native Hawaiian', 'American Indian or Alaska Native', 'Two or More Races']
nj_demo_list=[40.5,31.2,15.0,10.4,0.2,0.2,2.6]
nj_grad_dict={'labels':['White','Hispanic','Black or African American',
                        'Asian, Native Hawaiian, or Pacific Islander',
                        'American Indian or Alaska Native','Two or More Races'],
                'values':[46011/96514,24853/96514,13340/96514,10670/96514,116/96514,1434/96514]}
nj_grad_perc=[116/129,10670/10998,13430/15877,24853/29409,1434/1578,46011/48517]

fig=make_subplots(
    rows=3,cols=4,
    specs=[[{'type':'indicator'},{'type':'xy'},{'type':'xy'},{'type':'domain'}], [None,None,{'colspan':2,'type':'table'},None],[{'type':'indicator'},{'type':'domain'},{'type':'xy'},None]], 
    subplot_titles=('2021 Spending','2021 Spending by Pupil','SAT Performance','H.S. Graduation Demographics','HS Graduation Totals','Total Pupils','Racial Demographics'),
    column_widths=[0.15,0.25,0.35,0.25]
)

# First Row
fig.add_trace(go.Indicator(mode='number', value= 37331107709, 
                           domain={'x':[0,1], 'y':[0,1]},
                           number = {"prefix": "$"}, 
                           ),
              row=1, col=1)
fig.add_trace(go.Bar(x=['New Jersey', 'US'],y=[27455,14347], marker_color=['red','blue'], text=(['$27,455','$14,347']), textposition='inside' ), 
              row=1, col=2)


fig.add_trace(go.Bar(name='Reading and Writing',x=['New Jersey', 'US'],y=[557,533],text=(['RW:557','RW:533']), textposition='inside'), 
             row=1, col=3)
fig.add_trace(go.Bar(name='Math',x=['New Jersey', 'US'],y=[560,528],text=(['M:560','M:528']),textposition='inside')
             ,row=1, col=3)
fig.add_trace(go.Pie(**nj_grad_dict), 
              row=1, col=4)

# Second Row
fig.add_trace(go.Table(columnwidth=[2,2,3,3],header=dict(values=['Race','Cohort Total','Graduated', 'Percent Graduated'], fill_color='lightblue'),
                        cells=dict(values=[['American Indian or Alaska Native','Asian,Native Hawaiian,or Pacific Islander','Black or African American','Hispanic','Two or More Races','White'],
                                            [129,10998,15877,29409,1578,48517],
                                            [116,10670,13430,24853,1434,46011],
                                            [89.9,97.0,84.5,84.5,90.8,94.8]])), 
              row=2, col=3)

# Third Row
fig.add_trace(go.Indicator(mode='number', value=1359719, domain={'x':[0,1],'y':[0,1]}), 
              row=3, col=1)
fig.add_trace(go.Pie(labels=labels_list, values=nj_demo_list), 
              row=3, col=2)
fig.add_trace(go.Bar(x=['Female', 'Male', 'Eco Disadvantaged'],y=[49,51,32.7], text=['49%','51%','32.7%'], textposition= 'inside',marker_color=['red','blue'] ), 
              row=3, col=3)


# Figure design
fig.update_layout(paper_bgcolor='whitesmoke',title_text='New Jersey Education Snapshot (2021)', 
                  title_x=0.5, title_font_size=50, barmode='group', title_font_lineposition='under',showlegend=False)